# Problem 3: CpG Islands

---

## Background

### What is a CpG dinucleotide?

A **CpG dinucleotide** is a cytosine (C) followed immediately by a guanine (G) in the 5'→3' direction of a DNA strand. The "p" in CpG refers to the phosphodiester bond connecting the two nucleotides — this distinguishes it from a C-G base pair across two strands. For example, in the sequence `ACGTACG`, CpG dinucleotides occur at positions 2 and 6 (the `CG` pairs reading left to right).

### What are CpG islands?

**CpG islands** are regions of DNA with a higher frequency of CpG dinucleotides than you would expect by chance. They are biologically significant because they are often found in the promoter regions (5' ends) of vertebrate genes, making them useful markers for identifying potential genes in genomic sequences.

CpG islands were first formally defined by Gardiner-Garden and Frommer (1987) [1], who proposed a computational algorithm for detecting them using a sliding window approach. In 2002, Takai and Jones [2] published a refined algorithm with stricter thresholds that reduced false positives. Identification of CpG islands remains an active research topic, and modern approaches use more advanced mathematical and computational methods. For this exercise, you will implement the original Gardiner-Garden and Frommer algorithm.

### The Gardiner-Garden and Frommer Algorithm

The algorithm uses a **200 bp sliding window** that moves across the sequence **1 bp at a time**. For each window position, two values are computed:

![CpG Sliding Window Diagram](assets/cpg-window.png)

**1. GC-Content (%):** The percentage of bases in the window that are G or C:

$$\text{GC-content} = \frac{(\text{count of G} + \text{count of C})}{\text{window length}} \times 100$$

**2. Observed/Expected CpG Ratio:** The ratio of the actual count of CpG dinucleotides in the window to the count you would statistically expect:

$$\text{Observed} = \text{count of CG dinucleotides in the window}$$

$$\text{Expected} = \frac{\text{count of C} \times \text{count of G}}{\text{window length}}$$

$$\text{Obs/Exp} = \frac{\text{Observed}}{\text{Expected}}$$

A window is classified as part of a **CpG island** if **both** of the following conditions are met:

- Obs/Exp ratio **> 0.6**
- GC-content **> 50%**

### A quick note on "Observed" vs "Expected"

The **Observed** value is simply how many times the pattern `CG` appears in the window — count every position where a `C` is immediately followed by a `G`.

The **Expected** value estimates how many `CG` pairs you would expect to see *by chance* if the bases in the window were randomly distributed. If a window has many C's and many G's, you'd expect more `CG` pairs by chance. If there are very few of either, you'd expect fewer. The ratio tells you whether CpG dinucleotides are appearing more often than random chance would predict.

## Task

Implement the Gardiner-Garden and Frommer algorithm and use it to identify all CpG islands in Human [Chromosome 21](https://www.ncbi.nlm.nih.gov/nuccore/NC_000021?report=fasta).

### Setup

Due to the size of the Chromosome 21 FASTA file (~46 MB), it is not included in the repository. You will need to download it from NCBI and place it in the `data/` directory. Use your FASTA parser from the previous assignment to read the file.

> **Important:** Add the Chromosome 21 FASTA file to your `.gitignore` so it is not uploaded to GitHub. The file is too large for version control. Your `.gitignore` should include a line like:
> ```
> data/NC_000021*
> ```

### Implementation

Write your CpG island detection function in `src/module_2_assignment/cpg_islands.py`. Your function should:

1. Take a DNA sequence string as input.
2. Slide a 200 bp window across the sequence at 1 bp intervals (the window at position *i* covers bases *i* through *i* + 199).
3. For each window, compute the GC-content and Obs/Exp CpG ratio.
4. Report each window that meets **both** thresholds (Obs/Exp > 0.6 **and** GC-content > 50%).

Use **1-based indexing** for reporting positions (the first base in the sequence is position 1).

Report each qualifying window individually in the following format:

```
CpG island detected in region X to Y (Obs/Exp = Z.ZZ and %GC = ZZ.ZZ)
```

Where `X` is the start position, `Y` is the end position, `Obs/Exp` is rounded to 2 decimal places, and `%GC` is rounded to 2 decimal places.

> **Tip:** Test your implementation on the small example below before running it on the full Chromosome 21 sequence. The chromosome is large and your algorithm may take some time to process.

### Handling the `N` character

Genome assemblies sometimes contain `N` characters, which represent bases that could not be determined during sequencing. Since you do not know whether an `N` is a C or G, **exclude `N` from all counts** — do not count it as C, G, A, or T. However, `N` still occupies a position in the sequence, so the **window always spans exactly 200 positions** regardless of how many `N`s it contains. Use the full window length of 200 as the denominator in your formulas.

### Unit Testing

Write at least **one unit test** in `tests/test_cpg_islands.py`. Use the example below as a test case — your function should detect CpG islands at the expected positions. Run your tests from the command line:

```
pytest tests/test_cpg_islands.py
```

## Example

Given the following sequence (1,200 bases):

```
taacatacttattgtttttaactactcgttttccattcgactcatcacgctccccccccc
cccccccccccttatccgttccgttcgacgtatttcgttgtctaatttctgacgtaactt
gttccctgttaagtaccgtttatggcctatactccggtatttaaaacgacgacgattcca
ccgtaaagccgtcaaccagatgaacgacctcgctcgttatatttttccggcaaaatccct
atttccgattcgcttagtgctaccgacgctatatcgttccgcaattcctcgagatcatcg
atttcttctccggcgacgtctcaagtttttccgttacaacgcgatctatcctgtaaattc
gaccgcgctcattctcacgttttatacattgcgcagttgattacgctaaataatccgctg
actgttaccttccctgttagattcgcgcattataaactacttactttaacaaacgatttt
cacagtttaatttctgcgatgacgtctaactcttcagttttaaccgataacaaccttctc
gacacttcgtttcttataccatcctcgttatccatacccattcttaaatttctcactact
attctctttacaaccacattagctctaatcttacatctaatttctatacataaaatgctc
cttctgctgtatgtttctctttctcataattacatttttaattactaaatccctcatccc
tcccacccatctattccaccatcaaggttatacaccatgtattactgtaaaacccactaa
tattaattgtcaccgatattaaacgaaattcattcacacaaatttcattaattacctttt
cttattaattgcatatgtactctacatatactcaaccaactaaaaatcgatattttacat
ttgatttctaatgtaccccacaactttcttgctttatgattgaacttagctttataataa
tagttatttaccctaacgcatatactcttatccttatatgaaccttgcttatttgttaga
tttatccaatctaaaccacagataatatcccttctcttacttcattttattatcaccatt
ttcacttcttcctagatatatacaattatataactctattaccacattttcccttaactt
tctgttctgcactattatatttactctttttctaaaaccttcttaactttttcagatgca
```

**Expected output:**

```
CpG island detected in region 32 to 231 (Obs/Exp = 1.75 and %GC = 50.50)
CpG island detected in region 33 to 232 (Obs/Exp = 1.75 and %GC = 50.50)
```

These two results represent overlapping windows — window starting at position 32 and window starting at position 33 both meet the CpG island criteria. Each qualifying window is reported individually.

## Analysis

After running your algorithm on Chromosome 21, reflect on your results. Consider the following:

- How many CpG islands did your algorithm detect?
- Are the islands evenly distributed across the chromosome, or do they appear to cluster in certain regions?
- Given that CpG islands are associated with gene promoter regions, what might the distribution suggest about where genes are located on Chromosome 21?
- What limitations might the Gardiner-Garden and Frommer algorithm have, and how might the Takai and Jones refinements [2] address them?

---

## Online References

The following online CpG island calculators can be used to verify your results or explore how different tools approach the problem:

- [CpG Islands — GenScript](https://www.genscript.com/sms2/cpg_islands.html)
- [EMBOSS: cpgplot](http://emboss.sourceforge.net/apps/release/6.3/emboss/apps/cpgplot.html)

## References

1. Gardiner-Garden, M. and Frommer, M. CpG islands in vertebrate genomes. *Journal of Molecular Biology*, 196(2), 261–282 (1987). https://pubmed.ncbi.nlm.nih.gov/3656447/ PDF: [research/gardiner-garden-frommer-1987-cpg-islands.pdf](../research/gardiner-garden-frommer-1987-cpg-islands.pdf)
2. Takai, D. and Jones, P.A. Comprehensive analysis of CpG islands in human chromosomes 21 and 22. *Proceedings of the National Academy of Sciences*, 99(6), 3740–3745 (2002). https://pubmed.ncbi.nlm.nih.gov/11891299/ PDF: [research/takai-jones-2002-cpg-islands.pdf](../research/takai-jones-2002-cpg-islands.pdf)

In [ ]:
from module_2_assignment.fasta_parser import read_fasta
from module_2_assignment.cpg_islands import cpg_islands
# Overlapping cpg islands are counted as separate islands here and hence the huge number.
file_path= '../data/NC_000021.fasta'
counter=0
for description, sequence in read_fasta(file_path):
    cpg_islands_list = cpg_islands(sequence)
    print(f"Number of CpG islands for {description}: {len(cpg_islands_list)}")
    counter += len(cpg_islands_list)
    for start, end, obs_exp, gc_pct in cpg_islands_list:
        print(f"CpG island detected in region {start} to {end} (Obs/Exp = {obs_exp:.2f} and %GC = {gc_pct*100:.2f})")
    print()

print(f"Total number of CpG islands detected: {counter}")

Number of CpG islands for NC_000021.9 Homo sapiens chromosome 21, GRCh38.p14 Primary Assembly: 885021
CpG island detected in region 5010554 to 5010753 (Obs/Exp = 0.87 and %GC = 50.50)
CpG island detected in region 5010555 to 5010754 (Obs/Exp = 0.87 and %GC = 50.50)
CpG island detected in region 5010556 to 5010755 (Obs/Exp = 0.87 and %GC = 50.50)
CpG island detected in region 5010557 to 5010756 (Obs/Exp = 0.85 and %GC = 51.00)
CpG island detected in region 5010558 to 5010757 (Obs/Exp = 0.84 and %GC = 51.50)
CpG island detected in region 5010559 to 5010758 (Obs/Exp = 0.84 and %GC = 51.50)
CpG island detected in region 5010560 to 5010759 (Obs/Exp = 0.84 and %GC = 51.50)
CpG island detected in region 5010561 to 5010760 (Obs/Exp = 0.84 and %GC = 51.50)
CpG island detected in region 5010562 to 5010761 (Obs/Exp = 0.85 and %GC = 51.00)
CpG island detected in region 5010563 to 5010762 (Obs/Exp = 0.87 and %GC = 50.50)
CpG island detected in region 5010564 to 5010763 (Obs/Exp = 0.87 and %GC = 50.

## Analysis

After running your algorithm on Chromosome 21, reflect on your results. Consider the following:

- How many CpG islands did your algorithm detect?

885021

- Are the islands evenly distributed across the chromosome, or do they appear to cluster in certain regions?

The CpG islands are not evenly distributed across the chromosome. They appear to cluster in certain regions, with a particularly high concentration toward the starting regions of Chromosome 21.

- Given that CpG islands are associated with gene promoter regions, what might the distribution suggest about where genes are located on Chromosome 21?

Since CpG islands are commonly associated with gene promoter regions, the high concentration of CpG islands toward the starting regions of Chromosome 21 suggests that genes may also be more concentrated in these regions.

- What limitations might the Gardiner-Garden and Frommer algorithm have, and how might the Takai and Jones refinements [2] address them?

The Gardiner-Garden and Frommer algorithm may produce false positives because its relatively small window size and less stringent thresholds can classify short, CpG-rich regions as CpG islands even when they are not actual CpG islands. Takai and Jones refined the criteria by using a larger window size and stricter thresholds for GC content and observed-to-expected CpG ratio. These stricter requirements reduce false positives and identify longer, more biologically relevant CpG islands that are more likely to be associated with gene regulatory regions.